# 2. Análisis exploratorio

Este capítulo acompaña la pestaña **2. Análisis exploratorio** del dashboard y sigue su orden: objetivo
y tiempo, variables y relaciones, espacio y fuga de datos. Cada figura del dashboard aparece aquí con
su interpretación; los recuadros **Detalle** contienen análisis que no se muestran en pantalla.

Todo el EDA usa solo el conjunto de entrenamiento (semanas objetivo de 2018 a octubre de 2024). La
prueba se reservó antes de cualquier decisión de modelado.

In [1]:
import sys

sys.path.insert(0, "../src")
import numpy as np
import pandas as pd
import plotly.io as pio

import figuras as F
from modelo_utils import ETIQUETAS

pio.renderers.default = "notebook_connected"
pd.set_option("display.float_format", lambda x: f"{x:,.3f}")
pd.set_option("display.width", 160)
R = F.resumen()
K, E = R["kpis"], R["eda"]
T, S = E["temporal"], E["espacial"]

## 2.1 Variable objetivo y tiempo

### Serie semanal de la tasa de interrupción

In [2]:
F.fig_serie("total")

In [3]:
pd.DataFrame(T["eventos"]).assign(tasa_fuera=T["tasa_fuera_eventos"])

,evento,inicio,fin,tasa,maximo,tasa_fuera
0,Confinamiento COVID-19,2020-03-23,2020-05-31,0.318,0.402,0.279
1,Paro nacional 2021,2021-04-28,2021-06-15,0.353,0.550,0.279


**Interpretación.** La tasa semanal oscila alrededor de 28 % (28,2 % en entrenamiento) sin tendencia
marcada, pero con picos que afectan a muchos corredores a la vez. El más alto coincide con el paro
nacional de 2021: en la semana del 3 de mayo se interrumpió 55 % de los corredores y el promedio del
periodo fue 35,3 %. El confinamiento de 2020 elevó la media a 31,8 %, frente a 27,9 % fuera de ambos
eventos. Son choques comunes que ninguna variable individual del corredor puede anticipar; tienen dos
consecuencias para el modelado: la validación debe ser cronológica y los intervalos de confianza deben
remuestrear semanas completas, no filas.

In [4]:
F.fig_serie("region_origen", ["Andina", "Caribe", "Pacífica", "Orinoquía", "Amazonía"])

In [5]:
pd.DataFrame(S["correlacion_regional"]).round(2)

,Amazonía,Andina,Caribe,Orinoquía,Pacífica
Amazonía,1.000,0.600,0.270,0.400,0.620
Andina,0.600,1.000,0.170,0.490,0.510
Caribe,0.270,0.170,1.000,-0.250,0.080
Orinoquía,0.400,0.490,-0.250,1.000,0.550
Pacífica,0.620,0.510,0.080,0.550,1.000


**Interpretación.** Al desagregar por región de origen (selector *Desagregar por* del dashboard), la
región Andina, que aporta dos de cada tres filas, tiene la tasa más baja (26,4 %), mientras el Caribe,
la Orinoquía y la Amazonía están por encima de 34 %. Las series trimestrales de la región Andina, el
Pacífico, la Amazonía y la Orinoquía están correlacionadas entre sí; el Caribe sigue una dinámica
propia, con correlaciones bajas o negativas frente a las demás regiones. Esto justifica incluir el
departamento de origen como predictora y evaluar el modelo por región.

In [6]:
F.fig_serie("mercado", ["Bogotá, D.C., Corabastos", "Medellín, Central Mayorista de Antioquia",
                        "Cartagena, Bazurto", "Bogotá, D.C., Plaza Las Flores"])

**Interpretación.** Por central, las diferencias de nivel son grandes y persistentes: las plazas
minoristas de Bogotá (Las Flores, Samper Mendoza) superan 45 %, mientras Ipiales y Armenia están cerca
de 19 %. Las grandes centrales (Corabastos, Central Mayorista de Antioquia) tienen series más suaves
porque agregan muchos corredores grandes. La central de destino también entra al modelo.

### Estacionalidad y calendario

In [7]:
F.fig_estacionalidad()

In [8]:
pd.DataFrame(E["festivos"]).rename(columns={"mean": "tasa", "size": "n"})

,festivos_t1,tasa,n
0,0,0.276,425573
1,1,0.290,183862
2,2,0.378,10802
3,3,0.400,2007


**Interpretación.** Las diferencias entre meses son significativas (Kruskal-Wallis H = 82,5,
p ≈ 5·10⁻¹³): marzo (mediana 29,9 %), abril (29,2 %) y diciembre (28,9 %) tienen las medianas más
altas, y febrero (26,2 %) la más baja. Los picos aislados de enero corresponden a la primera semana del
año. La causa visible son los festivos: sin festivos en la semana siguiente la tasa es 27,6 %; con uno, 29,0 %; con
dos, 37,8 %, y con tres (Semana Santa, fin de año), 40,0 %. Como el calendario se conoce de antemano,
se incluyen como predictoras el número de festivos de $t+1$ y la semana del año codificada con seno y
coseno, que capta el ciclo anual sin el salto artificial entre la semana 52 y la 1.

:::{admonition} Detalle: descomposición STL y estacionariedad
:class: note
La descomposición STL (periodo de 52 semanas) separa una tendencia débil (fuerza 0,08) de una
estacionalidad anual moderada (fuerza 0,41). La serie es estacionaria: la prueba ADF rechaza la raíz
unitaria (estadístico −12,0; p ≈ 3·10⁻²²) y la KPSS no rechaza la estacionariedad en nivel (p ≥ 0,10).
Definir la interrupción como una caída **relativa** al propio corredor eliminó la tendencia que sí
tiene el volumen de carga.
:::

In [9]:
F.fig_stl()

In [10]:
pd.Series(T["punto_cambio"]).to_frame("punto de cambio en la media")

,punto de cambio en la media
fecha,2023-05-08
antes,0.286
despues,0.267


El único punto de cambio en la media (segmentación binaria) se ubica en mayo de 2023, con una
reducción pequeña (28,6 % → 26,7 %) que coincide con la ampliación del operativo del DANE a nuevas
centrales. No altera la definición del problema, pero explica por qué la tasa de prueba (26,0 %) es
algo menor que la de entrenamiento (28,2 %).

### Dependencia temporal

In [11]:
F.fig_acf()

In [12]:
F.fig_autocorr_corredor()

**Interpretación.** La ACF de la tasa nacional vale 0,44 en el rezago 1, cae por debajo de la banda
de significancia hacia la cuarta semana y reaparece en los rezagos 51-53 (0,19 a 0,26), la huella del
ciclo anual. La PACF solo es significativa en el rezago 1: un patrón de tipo AR(1) más un componente
estacional. Dentro de cada corredor, la interrupción de una semana se correlaciona 0,28 con la de la
semana previa, 0,10 con la de ocho semanas antes y se estabiliza en 0,11-0,13 a 13, 26 y 52 semanas,
lo que refleja diferencias persistentes entre corredores. **Decisiones:** usar el nivel de la semana
actual y la anterior relativos al promedio (`ratio_t`, `ratio_t_1`) y ventanas de 8 y 26 semanas, y
validar con bloques de semanas separados por un hueco.

:::{admonition} Detalle: deriva temporal
:class: note
El índice de estabilidad poblacional (PSI) entre 2019 y cada año posterior es menor que 0,01 en todas
las predictoras del corredor: no hay deriva de covariables. La excepción es la fracción nacional de
corredores en caída (`frac_caida_nacional_t`), con PSI de 0,24 a 2,80, porque es un único valor por
semana que cambia con cada choque; se dejó en observación y el capítulo 3 comprueba que el modelo no
depende de ella.
:::

In [13]:
F.tabla("deriva_psi").pivot(index="variable", columns="anio", values="psi").round(3)

anio,2020,2021,2022,2023,2024
variable,,,,,
activas26,0.005,0.008,0.003,0.001,0.002
cv8,0.002,0.006,0.002,0.001,0.001
dist_km,0.000,0.001,0.001,0.001,0.002
frac_caida_nacional_t,0.298,1.494,1.421,0.238,2.801
log_base8,0.001,0.003,0.003,0.002,0.003
n_envios8,0.001,0.002,0.001,0.000,0.002
ratio_t,0.001,0.003,0.001,0.001,0.001


## 2.2 Variables y relaciones con la interrupción

### Distribuciones por clase y tasa por deciles

El dashboard permite elegir cualquier predictora numérica. Aquí se interpretan las cuatro más
informativas.

In [14]:
F.fig_distribucion("cv8")

In [15]:
F.fig_deciles("cv8")

**Coeficiente de variación de 8 semanas (`cv8`).** Es la predictora con mayor tamaño de efecto
(|rbc| = 0,51; AUC univariado 0,753). Su mediana es 0,93 en las semanas previas a una interrupción y
0,48 en las demás. La relación es monótona y fuerte: la tasa de interrupción pasa de 2,3 % en el decil
más estable a 55,1 % en el más variable. Un corredor que ya oscila mucho tiene más probabilidad de caer
por debajo de la mitad de su promedio.

In [16]:
F.fig_distribucion("n_envios8", escala_log=True)

In [17]:
F.fig_deciles("n_envios8")

**Cargas por semana (`n_envios8`).** La distribución original es muy asimétrica (asimetría 8,0,
curtosis 90; 12,9 % de valores fuera de 1,5·IQR), por eso el dashboard ofrece la escala logarítmica y el
modelo usa `log1p`. Los corredores que se interrumpen tienen una mediana de 1,9 cargas semanales frente a
6,9 de los demás (|rbc| = 0,49): con una o dos cargas por semana basta que un camión no salga para que el
corredor «se interrumpa».

In [18]:
F.fig_deciles("ratio_t")

**Dinámica reciente (`ratio_t`).** La relación tiene forma de **U**: la tasa de interrupción es 52,7 %
en el decil más bajo (semanas en que el corredor ya trajo poco o nada), baja a 13,9 % cuando el
abastecimiento está cerca de su promedio (ratio ≈ 1) y vuelve a subir a 35,4 % tras un pico (ratio ≈ 2,6),
porque los picos suelen ser seguidos de un regreso brusco. Un modelo lineal en `ratio_t` no puede
representar una U; por eso el pipeline usa **splines cúbicos** para esta variable y la anterior.

In [19]:
F.fig_deciles("activas26")

**Regularidad semestral (`activas26`).** Como la mitad de las filas corresponde a corredores activos
todas las semanas del último semestre, los deciles se funden en seis grupos. Esos corredores plenamente
regulares tienen una tasa de 12,6 %; la tasa sube a 30,5 % cuando falta carga en 1 de cada 10 semanas y
llega a 57,4 % en los corredores activos solo un tercio del tiempo (|rbc| = 0,47).

:::{admonition} Detalle: estadísticos descriptivos de todas las predictoras
:class: note
La tabla resume el conjunto de entrenamiento completo. Escala (`base8`), cargas (`n_envios8`) y
productos (`n_alimentos8`) son muy asimétricas y se transforman con `log1p`; las razones de cambio tienen
entre 4 y 5 % de valores fuera de 1,5·IQR, que son picos reales y se recortan en los percentiles 1 y 99
(winsorización aprendida en entrenamiento) en lugar de eliminarse.
:::

In [20]:
F.tabla("descriptivos").set_index("variable")[["mean", "50%", "std", "min", "max", "asimetria", "curtosis", "pct_outliers_iqr"]].round(3)

,mean,50%,std,min,max,asimetria,curtosis,pct_outliers_iqr
variable,,,,,,,,
log_base8,1.647,1.394,1.119,0.002,6.242,0.880,0.219,1.165
ratio_t,1.000,0.943,0.768,0.000,7.965,1.445,4.510,4.456
ratio_t_1,0.999,0.950,0.745,0.000,7.965,1.410,4.569,4.445
cv8,0.681,0.605,0.411,0.000,2.814,0.678,-0.045,0.460
pend8_rel,-0.000,0.000,0.143,-1.083,0.953,-0.003,1.343,6.651
activas8,6.886,8.000,1.457,4.000,8.000,-0.920,-0.688,0.000
activas26,0.823,0.960,0.225,0.154,1.000,-1.135,0.130,1.050
n_envios8,19.810,4.500,53.993,0.500,"1,103.000",7.961,90.425,12.900
n_alimentos8,4.069,2.000,5.511,0.500,96.125,4.030,28.551,8.532


### Variables categóricas

In [21]:
F.fig_tasa_categoria("grupo_dom")

In [22]:
F.fig_tasa_categoria("pdet_origen")

In [23]:
F.tabla("categoricas").round(4)

,variable,categorias,chi2,gl,p,v_cramer
0,mercado,32,"8,364.012",31,0.000,0.116
1,depto_origen,30,"8,732.901",29,0.000,0.118
2,grupo_dom,8,"10,777.366",7,0.000,0.132
3,mismo_depto,2,"6,428.636",1,0.000,0.102
4,local,2,"2,418.882",1,0.000,0.062
5,pdet_origen,2,973.981,1,0.000,0.040
6,region_origen,5,"3,272.431",4,0.000,0.072


**Interpretación.** El grupo de alimentos dominante es la categórica más asociada con la interrupción
(V de Cramér = 0,13): los corredores de pescados (45,2 %), granos (41,2 %) y procesados (36,2 %) se
interrumpen más que los de verduras (21,9 %), carnes (23,4 %) y tubérculos (24,1 %), productos de
abastecimiento continuo. Los corredores que nacen en municipios **PDET** se interrumpen más (33,4 %
frente a 27,6 %), aunque la asociación es débil (V = 0,04). El capítulo 3 muestra que esa diferencia
desaparece al controlar por tamaño, regularidad y distancia. Con más de 600 mil filas todas las pruebas
χ² son significativas; lo informativo es la V de Cramér.

### Asociación con el objetivo

In [24]:
F.fig_asociacion("rbc")

In [25]:
F.fig_asociacion("info_mutua")

In [26]:
F.tabla("asociacion_objetivo").query("tipo == 'predictora'").sort_values("auc_univariado", ascending=False)[
    ["variable", "mediana_interr", "mediana_no", "rbc", "p_holm", "auc_univariado", "info_mutua"]].head(15)

,variable,mediana_interr,mediana_no,rbc,p_holm,auc_univariado,info_mutua
3,cv8,0.933,0.484,0.506,0.000,0.753,0.089
7,n_envios8,1.875,6.875,-0.485,0.000,0.743,0.080
6,activas26,0.720,1.000,-0.474,0.000,0.737,0.086
8,n_alimentos8,1.125,2.625,-0.434,0.000,0.717,0.065
5,activas8,6.000,8.000,-0.418,0.000,0.709,0.072
0,log_base8,0.909,1.653,-0.404,0.000,0.702,0.057
1,ratio_t,0.687,0.987,-0.212,0.000,0.606,0.055
2,ratio_t_1,0.750,0.984,-0.172,0.000,0.586,0.052
16,sh_verduras,0.000,0.018,-0.170,0.000,0.585,0.017
4,pend8_rel,-0.030,0.006,-0.162,0.000,0.581,0.040


**Interpretación.** Las pruebas de Mann-Whitney, corregidas por comparaciones múltiples con Holm, dan
p ≈ 0 para casi todas las variables; por eso se ordenan por tamaño del efecto (correlación biserial de
rangos, |rbc|) y por información mutua, que capta relaciones no lineales. Ambas medidas coinciden en que
las variables de **tamaño y regularidad** (`cv8`, `n_envios8`, `activas26`, `n_alimentos8`, `activas8`,
`log_base8`) dominan, con |rbc| entre 0,40 y 0,51; la **dinámica reciente** (`ratio_t`, `ratio_t_1`,
`pend8_rel`) tiene un efecto intermedio, y el calendario y la mayoría de las participaciones por grupo
aportan poco por sí solos.

### Correlación y multicolinealidad

In [27]:
F.fig_correlacion()

In [28]:
F.tabla("vif").round(2).head(10)

,variable,vif
0,activas8,4.480
1,cv8,3.990
2,n_alimentos8,3.240
3,sh_frutas,3.240
4,activas26,3.150
5,log_base8,3.030
6,n_envios8,3.000
7,pend8_rel,2.830
8,sh_verduras,2.710
9,sh_tuberculos,2.530


**Interpretación.** Las medidas de tamaño y regularidad están muy correlacionadas: `n_envios8` y
`n_alimentos8` (ρ = 0,91), `activas8` y `activas26` (0,83), `cv8` y `activas8` (−0,82). Aun así, ningún
VIF supera 5 (el máximo es 4,5, en `activas8`) una vez se omite una de las participaciones por grupo, que
suman 1 por construcción. Se conservan todas y el modelo usa regularización L2; al interpretar los
coeficientes se leen por bloques, no de forma aislada.

:::{admonition} Detalle: análisis multivariado (PCA, outliers y subpoblaciones)
:class: note
**PCA.** La primera componente explica 18 % de la varianza y se necesitan 12 de 22 para llegar a 80 %:
la información está repartida. PC1 es un eje de tamaño y regularidad y PC2 de dinámica reciente; las
interrupciones se concentran en un lado de PC1 pero se superponen mucho con la clase negativa, lo que
anticipa un desempeño moderado de un clasificador lineal.

**Outliers multivariados.** La distancia de Mahalanobis robusta marca 47 % de las filas y el Isolation
Forest 15 %. Una proporción tan alta indica una mezcla de subpoblaciones, no errores: los «atípicos»
son corredores pequeños (mediana de 1,6 cargas semanales frente a 12,6) con 45 % de interrupciones,
frente a 13 % en el núcleo. No se eliminan porque son la población de mayor riesgo.

**Subpoblaciones.** K-means sobre el perfil de cada corredor elige k = 2 (silueta 0,30): 2.141 corredores
pequeños, irregulares y lejanos (51 % de semanas con interrupción, 13,6 % PDET) y 992 consolidados (13,5 %).
:::

In [29]:
F.fig_pca()

In [30]:
pd.DataFrame(E["clusters"]["perfiles"]).round(3)

,cluster,corredores,tasa,pdet,cv8,log_base8,dist_km
0,0,2141,0.508,0.136,1.015,0.762,183.467
1,1,992,0.135,0.079,0.426,2.108,81.502


## 2.3 Componente espacial

In [31]:
F.fig_mapa_tasa("tasa")

**Interpretación.** El mapa muestra la tasa de interrupción de los 779 municipios con al menos 52
corredor-semanas. Las tasas más altas se agrupan en el Caribe (La Guajira, Cesar, Magdalena, Sucre) y
en zonas de la Orinoquía y el sur; las más bajas, en Norte de Santander, Antioquia y el Eje Cafetero.

In [32]:
F.fig_mapa_tasa("lisa")

In [33]:
F.fig_mapa_tasa("gi")

In [34]:
pd.Series({"I de Moran (k = 8)": S["moran_k8"], "p (999 permutaciones)": S["moran_p"], "I con k = 4": S["moran_k4"],
           "I con k = 12": S["moran_k12"], "municipios analizados": S["municipios_analizados"]}).to_frame("valor")

,valor
I de Moran (k = 8),0.247
p (999 permutaciones),0.001
I con k = 4,0.276
I con k = 12,0.223
municipios analizados,779.000


**Interpretación.** La tasa municipal tiene autocorrelación espacial positiva y significativa: I de
Moran = 0,247 (p = 0,001) con una matriz de 8 vecinos más cercanos, y el resultado se mantiene con 4
(0,276) y 12 vecinos (0,223). Se usan vecinos más cercanos y no contigüidad porque los municipios de
origen no cubren todo el territorio y su densidad es muy desigual. El LISA identifica 58 municipios
Alto-Alto y 88 Bajo-Bajo, y el estadístico Gi* de Getis-Ord confirma los mismos hotspots (Caribe,
costa nariñense) y coldspots (Norte de Santander, Antioquia, Eje Cafetero). **Consecuencia:** como los
municipios cercanos se parecen, el capítulo 3 valida también con bloques espaciales (departamentos no
vistos).

In [35]:
F.fig_mapa_tasa("cv8")

**Interpretación.** El mapa de variabilidad (`cv8`) reproduce buena parte del patrón de la tasa: parte
de la autocorrelación espacial de las interrupciones se explica porque los corredores pequeños e
irregulares también se agrupan en el espacio.

:::{admonition} Detalle: dispersión de Moran, semivariograma, escala y cobertura
:class: note
El diagrama de dispersión de Moran muestra la pendiente que define el I global. El semivariograma
crece hasta unos 125-350 km y luego se estabiliza en la varianza total; el efecto pepita es alto
(≈ 0,018 de una meseta de ≈ 0,026): buena parte de la variación es propia de cada municipio o corredor.
Agregado por departamento, el I de Moran cae a 0,01 (p = 0,31): la dependencia opera a escala municipal
y subregional (problema de la unidad de área modificable). Hay 210 municipios sin corredores regulares,
sobre todo en la Amazonía, el Pacífico y la Orinoquía, un sesgo de cobertura espacial.
:::

In [36]:
F.fig_moran_dispersion()

In [37]:
F.fig_semivariograma()

In [38]:
pd.Series(S["maup"]).to_frame("valor")

,valor
municipal,0.247
departamental,0.012
p_departamental,0.305
sd_municipal,0.159
sd_departamental,0.088


### Interacción espacio-tiempo

In [39]:
pd.DataFrame(S["por_anio"]).round(3)

,anio,municipios,moran,p,hotspots,jaccard
0,2018,685,0.229,0.005,66,NaN
1,2019,676,0.226,0.005,66,0.517
2,2020,664,0.192,0.005,70,0.374
3,2021,686,0.177,0.005,66,0.417
4,2022,692,0.186,0.005,77,0.474
5,2023,695,0.187,0.005,81,0.374
6,2024,684,0.219,0.005,80,0.412


In [40]:
pd.Series(S["knox"]).to_frame("prueba de Knox (≤ 50 km y ≤ 1 semana)")

,prueba de Knox (≤ 50 km y ≤ 1 semana)
observado,"2,312.000"
esperado,"1,474.747"
razon,1.568
p,0.010
eventos,"2,881.000"


**Interpretación.** La autocorrelación espacial es significativa todos los años, pero se debilita en
2020-2021 (I = 0,19 y 0,18), cuando los choques nacionales generalizaron las interrupciones, y se
recupera en 2024 (0,22). Los hotspots se desplazan: el índice de Jaccard entre años consecutivos va de
0,37 a 0,52. La prueba de Knox indica que los eventos de interrupción masiva (municipio-semana con al
menos dos tercios de sus corredores interrumpidos) ocurren juntos en espacio y tiempo 1,57 veces más de
lo esperado bajo independencia (p = 0,01): choques locales que afectan a varios municipios vecinos a la
vez. En el dashboard esta razón aparece como indicador junto al mapa.

## 2.4 Auditoría de fuga de datos

In [41]:
F.fig_asociacion("auc_univariado")

In [42]:
F.tabla("asociacion_objetivo").sort_values("auc_univariado", ascending=False)[["variable", "tipo", "auc_univariado"]].head(10)

,variable,tipo,auc_univariado
28,ratio_t1,control de fuga (excluida),1.000
27,tasa_t1,control de fuga (excluida),0.929
3,cv8,predictora,0.753
7,n_envios8,predictora,0.743
6,activas26,predictora,0.737
29,tasa_t,auxiliar,0.729
8,n_alimentos8,predictora,0.717
5,activas8,predictora,0.709
0,log_base8,predictora,0.702
30,base8,auxiliar,0.702


**Interpretación.** El AUC univariado de cada variable es un detector simple de fuga: un valor cercano a
1 indica que la variable contiene la respuesta. Las variables de control construidas con la semana
$t+1$ lo confirman: `tasa_t1 / base8` tiene AUC = 1,00 (define el objetivo) y `tasa_t1`, 0,93; ambas
están excluidas. Ninguna predictora admitida supera 0,753 (`cv8`), un valor coherente con una relación
real. El identificador del corredor (`cod_mpio`) se excluye para que el modelo no memorice la tasa
histórica de cada corredor; la central y el departamento se conservan como contexto (AUC con
codificación por objetivo de 0,56-0,57). Los días de encuesta de $t+1$ solo definen la población en
riesgo y nunca entran como predictora. Las variables `frac_caida_*` agregan la semana $t$ de todos los
corredores (no usan $t+1$) y quedan en observación.

**Lista final.** Predictoras: 24 numéricas, 3 binarias y 3 categóricas (tabla del capítulo 3).
Excluidas: `tasa_t1`, `tasa_t1 / base8`, `cod_mpio`, días de encuesta de $t+1$. En observación:
`frac_caida_mercado_t`, `frac_caida_nacional_t`.